In [34]:
import tensorflow as tf
import re
import numpy as np
from sklearn.model_selection import train_test_split
print("Success")

Success


In [35]:
# Menyiapkan data berbentuk sentence dan mempersiapkan sebelum sebelum di convert menjadi token
# Membersihkan sentence, membuat menjadu lowercase, menghapus karakter yang tidak diperlukan, etc

def preprocess_sentence(w):
    w = w.lower().strip() # Menghapus Spasi di awal + akhir
    w = re.sub(r"([?.!,])", r"\1", w) # Menambahkan spasi setelah tanda baca
    w = re.sub(r'[" "]+', " ", w) # menghapus spasi yang berlebih
    w = re.sub(r"[^a-zA-Z?.!,]+", " ", w) # Menghapus karakter selain alphanumeric
    w = w.strip() # Menghapus spasi di awal + akhir
    w = '<start> ' + w + ' <end>'
    return w
#Load data
def load_dataset(path, num_examples = None):
    with open(path, 'r', encoding='utf-8') as file:
        lines = file.read().strip().split("\n")
    parts = [line.split('\t') for line in lines[:num_examples]]
    input_data = [preprocess_sentence(part[0]) for part in parts]
    target_data = [preprocess_sentence(part[1]) for part in parts]
    return input_data, target_data


path_to_file = './ind.txt'
input_data, target_data = load_dataset(path_to_file, num_examples=100000)
print('Input data: ', input_data)
print('Target data: ', target_data)

Input data:  ['<start> hi. <end>', '<start> run! <end>', '<start> run. <end>', '<start> who? <end>', '<start> wow! <end>', '<start> wow! <end>', '<start> fire! <end>', '<start> fire! <end>', '<start> fire! <end>', '<start> help! <end>', '<start> jump! <end>', '<start> jump. <end>', '<start> stop! <end>', '<start> stop! <end>', '<start> wait! <end>', '<start> wait. <end>', '<start> hello. <end>', '<start> hurry! <end>', '<start> hurry! <end>', '<start> hurry! <end>', '<start> i see. <end>', '<start> i see. <end>', '<start> i see. <end>', '<start> i see. <end>', '<start> i see. <end>', '<start> i see. <end>', '<start> i won! <end>', '<start> i won. <end>', '<start> oh no! <end>', '<start> relax. <end>', '<start> relax. <end>', '<start> shoot! <end>', '<start> smile. <end>', '<start> attack! <end>', '<start> cheers! <end>', '<start> freeze! <end>', '<start> get up. <end>', '<start> got it! <end>', '<start> got it? <end>', '<start> he ran. <end>', '<start> i fell. <end>', '<start> i know. 

In [36]:
# Tokenize input dan target data
tokenizer = tf.keras.preprocessing.text.Tokenizer(filters='')
tokenizer.fit_on_texts(input_data + target_data) # bikin kamus, buat kaya masukin ke index dan itung berapa banyak munculnya 

# Convert sentences to integer Sequence
input_tensor = tokenizer.texts_to_sequences(input_data)
target_tensor = tokenizer.texts_to_sequences(target_data)

#Calculate max sequence lengths
max_length_targ, max_length_inp = max(len(seq) for seq in target_tensor), max(len(seq) for seq in input_tensor)


#Pad Sequences
input_tensor = tf.keras.preprocessing.sequence.pad_sequences(input_tensor, maxlen=max_length_inp, padding='post')
target_tensor = tf.keras.preprocessing.sequence.pad_sequences(target_tensor, maxlen=max_length_targ, padding='post')


# Calculate vocabulary size
vocab_size = len(tokenizer.word_index) + 1
print("input tensor = ", input_tensor)
print("target tensor = ", target_tensor)

input tensor =  [[    1  4449     2 ...     0     0     0]
 [    1  8569     2 ...     0     0     0]
 [    1  5761     2 ...     0     0     0]
 ...
 [    1 12055 12056 ...     0     0     0]
 [    1  7191  7192 ...     0     0     0]
 [    1   152    11 ...    27  2521     2]]
target tensor =  [[    1  5084     2 ...     0     0     0]
 [    1  7194     2 ...     0     0     0]
 [    1  7194     2 ...     0     0     0]
 ...
 [    1 16336 16337 ...     0     0     0]
 [    1  7191  7192 ...     0     0     0]
 [    1   277   614 ...     0     0     0]]


In [37]:
# Split data into train, val, test
input_tensor_train, input_tensor_val, target_tensor_train, target_tensor_val = train_test_split(input_tensor, target_tensor, random_state=67, test_size=0.2)


BUFFER_SIZE = len(input_tensor_train)
BATCH_SIZE = 64

dataset = tf.data.Dataset.from_tensor_slices((input_tensor_train, target_tensor_train)).shuffle(BUFFER_SIZE)
dataset = dataset.batch(BATCH_SIZE, drop_remainder=True)

print("Dataset : ", dataset)
for sample in dataset.take(1):
    input_sample, target_sample = sample
    print("INPUT SAMPLE= ", input_sample)
    print("TARGEt SAMPLE= ", target_sample)

Dataset :  <BatchDataset element_spec=(TensorSpec(shape=(64, 36), dtype=tf.int32, name=None), TensorSpec(shape=(64, 30), dtype=tf.int32, name=None))>
INPUT SAMPLE=  tf.Tensor(
[[   1    3   16 ...    0    0    0]
 [   1  234    4 ...    0    0    0]
 [   1  362 6955 ...    0    0    0]
 ...
 [   1  169    7 ...    0    0    0]
 [   1   29    7 ...    0    0    0]
 [   1    4  620 ...    0    0    0]], shape=(64, 36), dtype=int32)
TARGEt SAMPLE=  tf.Tensor(
[[   1    3  177 ...    0    0    0]
 [   1  601    6 ...    0    0    0]
 [   1 1749 1749 ...    0    0    0]
 ...
 [   1   22   15 ...    0    0    0]
 [   1   22   15 ...    0    0    0]
 [   1    6  385 ...    0    0    0]], shape=(64, 30), dtype=int32)


In [38]:
class Encoder(tf.keras.Model):
    def __init__(self, vocab_size, embedding_dim, enc_units, batch_size):
        super(Encoder, self).__init__()
        self.batch_size = batch_size
        self.enc_units = enc_units
        self.embedding = tf.keras.layers.Embedding(vocab_size, embedding_dim)
        self.gru = tf.keras.layers.GRU(self.enc_units, return_sequences=True, return_state=True, recurrent_initializer='glorot_uniform')
    
    
    def call(self, x, hidden):
        x = self.embedding(x)
        output, state = self.gru(x, initial_state = hidden)
        return output, state
    
    def initialize_hidden_state(self):
        return tf.zeros((self.batch_size, self.enc_units))
    
embedding_dim = 256
units = 1024
BATCH_SIZE = 64
example_input_batch = input_tensor_train[:BATCH_SIZE]

encoder = Encoder(vocab_size, embedding_dim, units, BATCH_SIZE)

sample_hidden = encoder.initialize_hidden_state()
sample_output, sample_hidden = encoder(example_input_batch, sample_hidden)

print('Encoder output shape : (batch size, sequence length, units) {}'.format(sample_output.shape))
print('Encoder hidden state shape : (batch size, units) {}'.format(sample_hidden.shape))

Encoder output shape : (batch size, sequence length, units) (64, 36, 1024)
Encoder hidden state shape : (batch size, units) (64, 1024)


# ATAS ITU DAPET DARI TEMPLATE DI SESI 5, MULAI DARI SINI SAMPAI BAWAH ITU BIKIN SENDIRI

In [39]:
import matplotlib.pyplot as plt
import matplotlib.ticker as ticker
import os
import time

In [40]:
steps_per_epoch = len(input_tensor_train) // BATCH_SIZE

inp_lang = tf.keras.preprocessing.text.Tokenizer(filters='')
inp_lang.fit_on_texts(input_data)

targ_lang = tf.keras.preprocessing.text.Tokenizer(filters='')
targ_lang.fit_on_texts(target_data)

Bikin layer Bahdanau

In [41]:
class BahdanauAttention(tf.keras.layers.Layer):
    def __init__(self, units):
        super(BahdanauAttention, self).__init__()
        self.W1 = tf.keras.layers.Dense(units) # utk hitung query
        self.W2 = tf.keras.layers.Dense(units) # utk hitung values
        self.V = tf.keras.layers.Dense(1) # utk hasil dari query dan values
        
    def call(self, query, values):
        query_with_time_axis = tf.expand_dims(query, 1) # untuk nambahin 1 dimensi
        score = self.V(tf.nn.tanh(self.W1(query_with_time_axis) + self.W2(values)))
        
        attention_weights = tf.nn.softmax(score, axis=1)
        
        context_vector = attention_weights * values
        context_vector = tf.reduce_sum(context_vector, axis=1)
        
        return context_vector, attention_weights
    
    
attention_layer = BahdanauAttention(10) # 10 neuron

attentions_results, attention_weight = attention_layer(sample_hidden, sample_output)

print(f"Attention Result shape: (Batch Size, units) : {attentions_results.shape}")
print(f"Attention Weights shape: (Batch Size, sequence length, 1) {attention_weight.shape}")

# Bahdanau attention kaya sistem penerjamahan bahasa
# Values -> bahasa asli
# query -> rekomendasi translate kata nya
# Bahdanau Attention, kaca pembesar

Attention Result shape: (Batch Size, units) : (64, 1024)
Attention Weights shape: (Batch Size, sequence length, 1) (64, 36, 1)


In [42]:
class Decoder(tf.keras.Model):
    def __init__(self, vocab_size, embedding_dim, dec_units, batch_size):
        super(Decoder, self).__init__()
        self.batch_size = batch_size
        self.dec_units = dec_units
        self.embedding = tf.keras.layers.Embedding(vocab_size, embedding_dim)
        self.gru = tf.keras.layers.GRU(self.dec_units, return_sequences=True, return_state=True, recurrent_initializer='glorot_uniform')
        self.fc = tf.keras.layers.Dense(vocab_size)
        self.attention = BahdanauAttention(self.dec_units)
    
    def call(self, x, hidden, enc_output):
        context_vector, attention_weight = self.attention(hidden, enc_output)
        x = self.embedding(x)
        x = tf.concat([tf.expand_dims(context_vector, 1)], axis = -1)
        output, state = self.gru(x)
        output = tf.reshape(output, (-1, output.shape[2]))
        x = self.fc(output)
        
        return x, state, attention_weight

bikin model atau object si decodernya

In [43]:
decoder = Decoder(vocab_size, embedding_dim, units, BATCH_SIZE)
sample_decoder_output, _, _ = decoder(tf.random.uniform((BATCH_SIZE, 1)), sample_hidden, sample_output)

print(f"Decoder output shape: {sample_decoder_output.shape}")

Decoder output shape: (64, 16354)


In [44]:
optimizer = tf.keras.optimizers.Adam(0.001)
loss_object = tf.keras.losses.SparseCategoricalCrossentropy(from_logits=True, reduction='none')

def loss_function(real, pred):
    mask = tf.math.logical_not(tf.math.equal(real, 0))
    loss_ = loss_object(real, pred)
    mask = tf.cast(mask, dtype=loss_.dtype)
    loss_ *= mask
    return tf.reduce_mean(loss_)

In [45]:
def train_step(inp, targ, enc_hidden):
    loss = 0
    with tf.GradientTape() as tape:
        enc_output, enc_hidden = encoder(inp, enc_hidden)
        dec_hidden = enc_hidden
        dec_input = tf.expand_dims([targ_lang.word_index['<start>']] * BATCH_SIZE, 1)
        
        for t in range(1, targ.shape[1]):
            predictions, dec_hidden, _ = decoder(dec_input, dec_hidden, enc_output)
            
            print(targ[:, t])
            print(predictions)
            loss += loss_function(targ[:, t], predictions)
            
    batch_loss = (loss / int(targ.shape[1]))
    variables = encoder.trainable_variables + decoder.trainable_variables
    gradient = tape.gradient(loss, variables)
    optimizer.apply_gradients(zip(gradient, variables))
    
    return batch_loss

In [46]:
EPOCH = 2
for epoch in range(EPOCH):
    start = time.time()
    enc_hidden = encoder.initialize_hidden_state()
    total_loss = 0
    for (batch, (inp, targ)) in enumerate(dataset.take(steps_per_epoch)):
        batch_loss = train_step(inp, targ, enc_hidden)
        total_loss += batch_loss
        
        if batch % 100 == 0:
            print(f"EPOCH {epoch + 1}, BATCH {batch}, LOSS {batch_loss.numpy():.4f}")
            
            
    print(f"EPOCH {epoch + 1}, LOSS {(total_loss / steps_per_epoch):.4f}")
    print(f"Time taken buat 1 epoch: {time.time() - start}")

tf.Tensor(
[    6  4118    18  1156  2574  1765   528     3    88 12098  2297     3
     6    22     3     3    24   459    18   101    48   465    18  4060
  5436 15041  1533  2657    17  2297   101     3   584    57     3  8256
    48   269    57     3   185     3   400     3   107   601   127     6
     6  2098  7933     6   128    22    22    86     3    24    66    18
   703    17    57  1880], shape=(64,), dtype=int32)
tf.Tensor(
[[ 1.3508595e-04 -1.9507366e-03 -7.8655407e-04 ...  1.5988695e-03
  -2.5502034e-03 -3.4101072e-04]
 [ 2.9739999e-04 -1.4452008e-03 -4.4974138e-04 ...  1.3870491e-03
  -2.3281756e-03 -3.2705165e-04]
 [ 1.3781397e-04 -2.1056177e-03 -8.4372266e-04 ...  1.7812563e-03
  -2.9126029e-03 -6.0442864e-04]
 ...
 [ 1.7123445e-04 -9.5390354e-04 -5.4390135e-04 ...  5.7018048e-04
  -1.7211719e-03  1.3174431e-06]
 [ 2.0181789e-04 -2.1838732e-03 -8.2878809e-04 ...  1.7544997e-03
  -2.9036182e-03 -6.3206739e-04]
 [ 4.9917900e-05 -2.0120544e-03 -8.7173237e-04 ...  1.786224

In [47]:
def evaluate(sentence):
    attention_plot = np.zeros((max_length_targ, max_length_inp))
    sentence = preprocess_sentence(sentence)
    inputs = [inp_lang.word_index[i] for i in sentence.split(' ')]
    inputs = tf.keras.preprocessing.sequence.pad_sequence([inputs], maxlen=max_length_inp, padding='post')
    inputs = tf.convert_to_tensor(inputs)
    
    result = ''
    hidden = [tf.zeros((1, units))]
    enc_output, enc_hidden = encoder(inputs, hidden)
    
    dec_hidden = enc_hidden
    dec_input = tf.expand_dims([targ_lang.word_index['<start>']], 0)
    
    for t in range(max_length_targ):
        predictions, dec_hidden, attentions_weight = decoder(dec_input, dec_hidden, enc_output)
        attentions_weight = tf.reshape(attentions_weight, (-1, ))
        attention_plot[t] = attentions_weight.numpy()
        
        prediction_id = tf.argmax(predictions[0]).numpy()
        
        result += targ_lang.index_word[prediction_id] + ' '
        
        if targ_lang.index_word[prediction_id] == '<end>':
            return result, sentence, attention_plot
    
        dec_input = tf.expand_dims([prediction_id, 0])
        
    return result, sentence, attention_plot
    
    

KeyError: 'aku'